# 06 — Heard space vs the 518 baseline: a general recommendation check

Two checks, both against the frozen catalogue (FMA small), before any subjective
listening happens:

1. **External seed.** My tutor suggested testing the recommender against real
   platforms: Spotify and YouTube were each given the same seed —
   *Elyjah Slaps the Space* — and their top recommendations were downloaded
   into `data/raw/spotify_tests` and `data/raw/youtube_tests` (9 tracks each,
   plus the shared seed). First the seed runs through our own recommender, as a
   sanity pass: does the pipeline work end to end, and are the picks plausible?
   Then all 18 of Spotify's and YouTube's actual recommendations are scored —
   not by ear, that's the listening check, later — but by where each one lands
   in *our* similarity ordering for that seed.

2. **Heard vs baseline, multi-seed.** `notebooks/05_multi_seed_taste.ipynb`
   explicitly flagged this as its next step: rerun the same multi-seed taste
   logic on the `heard` embedding (154 columns — mfcc + rhythm + harmonic/
   percussive ratio, see `notebooks/04_new_features.ipynb`) instead of the old
   518-feature baseline, and compare.

**A caveat that matters for part 1:** the seed mp3 never went through FMA's own
feature pipeline. `modeling/external.py` reproduces FMA's mfcc extraction
parameter-for-parameter (verified against a known FMA track's real
`features.csv` row — see that module's docstring), but it only matches closely,
not exactly: FMA's `features.csv` was built on an older librosa than we have
installed, so the mfcc block correlates 0.97–0.99 with the original on
mean/std/median/min/max, and only 0.73–0.90 on skew/kurtosis. Treat the
external-seed distances below as indicative, not exact — which is exactly what
a *general* check should be, ahead of the real listening comparison.

**Also worth knowing:** `modeling/train_pca.py --feature-set heard` — the exact
command in `FOR_TIM.md` — has a bug. `feature_set()` filters whatever columns
are already in `X`, and `train_pca.run()` passes it the 518-column FMA table
without ever joining in the rhythm/separation columns first — so it silently
fits PCA on the 140 mfcc columns alone, not the full 154-column heard space.
This notebook fits it correctly, via `features.space("heard")`, which does call
`full_table()`. Worth a heads up to whoever owns that branch.

In [1]:
import sys
sys.path.append("..")

from pathlib import Path
import tempfile
import os
import numpy as np
import pandas as pd
import librosa
import soundfile as sf
from IPython.display import Audio, display

from modeling.data import load_fma, genre_labels
from modeling.features import space, scale_features, fit_pca, transform, save_artifacts
from modeling.recommender import TrackRecommender
from modeling.external import extract_heard_features
from modeling.rhythm import audio_path
from modeling import taste as taste_mod

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
DATA_RAW = REPO_ROOT / "data" / "raw"
pd.set_option("display.max_colwidth", 60)

### A player, for listening along

Every clip below is a **20-second excerpt**, not the full track — embedding 50+
full mp3s in one notebook would make it enormous even compressed. Excerpts
start 10% into the track (skips cold intros/silence) and are gain-adjusted to
a common target RMS, capped so a near-silent clip is never amplified into
noise — the same spirit as `02_listening_test.ipynb`'s loudness matching, done
inline here since it's needed for both catalogue and external tracks alike.

Encoded as OGG/Vorbis, not raw WAV — `Audio(array, rate=sr)` embeds
uncompressed 16-bit PCM, which made an earlier version of this notebook
**over 150MB** and unrenderable in some editors. OGG cuts that by roughly 7x
at no audible cost for a 20s mono preview.

In [2]:
PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    y, sr = librosa.load(path, sr=22050, mono=True)
    skip = min(10.0, 0.1 * len(y) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(y))
    start = max(0, end - int(seconds * sr))
    clip = y[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

## Build both embeddings from the catalogue

In [3]:
# Baseline: all 518 FMA columns, exactly notebook 05's recipe.
X_baseline, tracks_baseline = load_fma(subset="small")
Xb_scaled, scaler_baseline = scale_features(X_baseline, method="standard")
pca_baseline = fit_pca(Xb_scaled, n_components=0.90)
rec_baseline = TrackRecommender(scaler_baseline, pca_baseline).fit(X_baseline, tracks_baseline)
print(f"baseline: {X_baseline.shape[1]} columns -> {pca_baseline.n_components_} components, "
      f"{len(tracks_baseline)} tracks")

baseline: 518 columns -> 146 components, 8000 tracks


In [4]:
# Heard: mfcc + rhythm + hpss_ratio, joined via full_table() -- NOT through the
# buggy train_pca.py path described above.
X_heard = space("heard")
tracks_heard = tracks_baseline.loc[X_heard.index]

Xh_scaled, scaler_heard = scale_features(X_heard, method="standard")
pca_heard = fit_pca(Xh_scaled, n_components=0.90)
rec_heard = TrackRecommender(scaler_heard, pca_heard).fit(X_heard, tracks_heard)

scaler_path, pca_path = save_artifacts(scaler_heard, pca_heard, suffix="_90pct_heard")
print(f"heard: {X_heard.shape[1]} columns -> {pca_heard.n_components_} components, "
      f"{len(tracks_heard)} tracks ({len(tracks_baseline) - len(tracks_heard)} dropped as incomplete)")
print("saved:", scaler_path.name, pca_path.name)

heard: 154 columns -> 57 components, 7993 tracks (7 dropped as incomplete)
saved: scaler_90pct_heard.pkl pca_90pct_heard.pkl


## 1. General recommendation check — the external seed

*Elyjah Slaps the Space* is the shared seed in both `spotify_tests` and
`youtube_tests`. Extract it in heard space, transform with the *fitted* scaler
and PCA (not refit), and see what the catalogue's nearest neighbours are.

In [5]:
SEED_PATH = DATA_RAW / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"
assert SEED_PATH.exists(), SEED_PATH

seed_row = extract_heard_features(SEED_PATH, X_heard.columns)
seed_embedding = transform(seed_row.to_frame().T, scaler_heard, pca_heard)

N = 10
distances, idx = rec_heard.index_.kneighbors(seed_embedding, n_neighbors=N)
seed_recs = rec_heard._with_metadata(rec_heard.track_ids_[idx[0]], distances[0], np.arange(1, N + 1))
seed_recs

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


,rank,distance,artist,title,genre
track_id,,,,,
127498,1,0.332982,Blue Dot Sessions,Scratcher,Instrumental
51260,2,0.333157,Les Filles et les Garçons,I Sing Despair,Pop
30895,3,0.333841,Digi G'Alessio,Camuffarsi e Mantenere la Calma (Al Pianobar),Electronic
42374,4,0.352820,Broke For Free,My Luck,Electronic
107426,5,0.360859,UncleBibby,Chunky Worm Stew,Electronic
47657,6,0.363693,Haute Culture,Post,Electronic
97544,7,0.363907,Amitron_7,Escape Under Cover of Night,Electronic
108422,8,0.393743,UncleBibby,YearBear,Electronic
56797,9,0.425073,Podington Bear,Herbie,Electronic


**Listen:** the seed, then our own top-10 heard-space picks for it.

In [6]:
play(SEED_PATH, "SEED — Elyjah Slaps the Space")
print()
for track_id, row in seed_recs.iterrows():
    play(audio_path(track_id),
         f"#{row['rank']}  distance={row['distance']:.3f}  {row['artist']} — {row['title']}  [{row['genre']}]")

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


SEED — Elyjah Slaps the Space



#1  distance=0.333  Blue Dot Sessions — Scratcher  [Instrumental]


#2  distance=0.333  Les Filles et les Garçons — I Sing Despair  [Pop]


#3  distance=0.334  Digi G'Alessio — Camuffarsi e Mantenere la Calma (Al Pianobar)  [Electronic]


...

#6  distance=0.364  Haute Culture — Post  [Electronic]


#7  distance=0.364  Amitron_7 — Escape Under Cover of Night  [Electronic]


#8  distance=0.394  UncleBibby — YearBear  [Electronic]


#9  distance=0.425  Podington Bear — Herbie  [Electronic]


#10  distance=0.430  Monk Turner + Fascinoma — Everything Already  [Pop]


For reference, the actual filenames: what Spotify and YouTube each recommended
for the same seed.

In [7]:
for folder in ["spotify_tests", "youtube_tests"]:
    tracks_in_folder = sorted(p.name for p in (DATA_RAW / folder).glob("*.mp3") if "Elyjah" not in p.name)
    print(f"{folder} ({len(tracks_in_folder)} recommendations):")
    for name in tracks_in_folder:
        print(" ", name)
    print()

spotify_tests (9 recommendations):
  Y2Mate.is - ELWD - U MAKE ME OFFICIAL VIDEO.mp3
  Y2Mate.is - Lola.mp3
  Y2Mate.is - Loure - In The Evenings.mp3
  Y2Mate.is - Melodiesinfonie - Peace On Earth.mp3
  Y2Mate.is - Naima Blue.mp3
  Y2Mate.is - Soul.mp3
  Y2Mate.is - Tour Maubourg - Ode To Love Official Video.mp3
  Y2Mate.is - gabriel Two Scents - Beauty In Imperfection.mp3
  Y2Mate.is - la danse.mp3

youtube_tests (9 recommendations):
  Y2Mate.is - 1999.mp3
  Y2Mate.is - Ahh.mp3
  Y2Mate.is - Careless Tiny Room Sessions.mp3
  Y2Mate.is - Desencantado.mp3
  Y2Mate.is - Gumbo.mp3
  Y2Mate.is - Rasheed.mp3
  Y2Mate.is - _You hate Jazz__.mp3
  Y2Mate.is - nyc in 1940.mp3
  Y2Mate.is - zeste.mp3



### Scoring them: where do Spotify's and YouTube's picks sit in *our* space?

Not a listening comparison — those files never went through a listener, and the
mfcc caveat from the intro still applies to every one of them. What this can
answer instead: extract each of the 18 recommended tracks in heard space the
same way the seed was, measure its cosine distance to the seed, and ask where
that distance would rank if the track were dropped into the catalogue's own
similarity ordering (1 = the catalogue's single closest match, ~7993 = its most
distant). Our own top-10 above rank 1-10 by construction; if Spotify's and
YouTube's picks cluster near the front of that same ordering, our notion of
"similar" agrees with theirs. If they scatter deep into the catalogue, it
doesn't — at least not in this feature space.

In [8]:
def cosine_distance_to_seed(embeddings: np.ndarray, seed_vec: np.ndarray) -> np.ndarray:
    seed_unit = seed_vec / np.linalg.norm(seed_vec)
    emb_unit = embeddings / np.linalg.norm(embeddings, axis=1, keepdims=True)
    return 1 - emb_unit @ seed_unit


seed_vec = seed_embedding.to_numpy()[0]
catalog_distances = np.sort(cosine_distance_to_seed(rec_heard.embedding_.to_numpy(), seed_vec))
catalog_size = len(catalog_distances)


def catalog_rank(distance: float) -> int:
    """1-based rank the track would hold if inserted into the catalogue's
    distance-to-seed ordering."""
    return int(np.searchsorted(catalog_distances, distance)) + 1


scored_rows = []
for folder in ["spotify_tests", "youtube_tests"]:
    for path in sorted((DATA_RAW / folder).glob("*.mp3")):
        if "Elyjah" in path.name:
            continue
        try:
            feat = extract_heard_features(path, X_heard.columns)
            emb = transform(feat.to_frame().T, scaler_heard, pca_heard).to_numpy()[0]
            distance = float(cosine_distance_to_seed(emb[np.newaxis, :], seed_vec)[0])
            scored_rows.append({"platform": folder, "file": path.name, "path": path,
                                 "distance_to_seed": distance, "catalog_rank": catalog_rank(distance)})
        except Exception as exc:
            scored_rows.append({"platform": folder, "file": path.name, "path": path,
                                 "distance_to_seed": np.nan, "catalog_rank": None, "error": str(exc)})

scored = pd.DataFrame(scored_rows).sort_values(["platform", "distance_to_seed"])
scored.drop(columns="path")

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


...

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


,platform,file,distance_to_seed,catalog_rank
5,spotify_tests,Y2Mate.is - Soul.mp3,0.465966,21
3,spotify_tests,Y2Mate.is - Melodiesinfonie - Peace On Earth.mp3,0.467541,21
7,spotify_tests,Y2Mate.is - gabriel Two Scents - Beauty In Imperfection.mp3,0.483183,31
1,spotify_tests,Y2Mate.is - Lola.mp3,0.513761,58
0,spotify_tests,Y2Mate.is - ELWD - U MAKE ME OFFICIAL VIDEO.mp3,0.528813,74
4,spotify_tests,Y2Mate.is - Naima Blue.mp3,0.601388,233
8,spotify_tests,Y2Mate.is - la danse.mp3,0.762448,1201
6,spotify_tests,Y2Mate.is - Tour Maubourg - Ode To Love Official Video.mp3,0.828068,1815
2,spotify_tests,Y2Mate.is - Loure - In The Evenings.mp3,0.908688,2781
16,youtube_tests,Y2Mate.is - nyc in 1940.mp3,0.430104,12


In [9]:
print(f"catalogue size: {catalog_size} tracks")
print(f"our own top-{N} heard-space distances to this seed: {seed_recs['distance'].round(3).tolist()}")
print()
print("distance_to_seed by platform:")
print(scored.groupby("platform")["distance_to_seed"].describe()[["count", "mean", "min", "max"]])
print()
print("catalog_rank by platform (1 = catalogue's closest match, "
      f"{catalog_size} = its most distant):")
print(scored.groupby("platform")["catalog_rank"].describe()[["count", "mean", "min", "max"]])

catalogue size: 7993 tracks
our own top-10 heard-space distances to this seed: [0.333, 0.333, 0.334, 0.353, 0.361, 0.364, 0.364, 0.394, 0.425, 0.43]

distance_to_seed by platform:
               count      mean       min       max
platform                                          
spotify_tests    9.0  0.617762  0.465966  0.908688
youtube_tests    9.0  0.605741  0.430104  0.745901

catalog_rank by platform (1 = catalogue's closest match, 7993 = its most distant):
               count        mean   min     max
platform                                      
spotify_tests    9.0  692.777778  21.0  2781.0
youtube_tests    9.0  408.111111  12.0  1068.0


**Listen:** all 18, closest-to-the-seed first within each platform — the same
order as the table above.

In [10]:
for row in scored.itertuples():
    label_text = f"[{row.platform}] rank={row.catalog_rank} distance={row.distance_to_seed:.3f}  {row.file}"
    play(row.path, label_text)

[spotify_tests] rank=21 distance=0.466  Y2Mate.is - Soul.mp3


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[spotify_tests] rank=21 distance=0.468  Y2Mate.is - Melodiesinfonie - Peace On Earth.mp3


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[spotify_tests] rank=31 distance=0.483  Y2Mate.is - gabriel Two Scents - Beauty In Imperfection.mp3


...

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[youtube_tests] rank=931 distance=0.730  Y2Mate.is - _You hate Jazz__.mp3


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[youtube_tests] rank=1068 distance=0.746  Y2Mate.is - Ahh.mp3


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


## 2. Heard vs baseline — the multi-seed taste check, rerun

Same three seeds and the same centroid logic as `05_multi_seed_taste.ipynb`
(`modeling/taste.py`), run once per embedding. Both are entirely within the
catalogue, so this side of the comparison carries none of the external-seed
caveat above.

In [11]:
SEED_IDS = [704, 1083, 56690]


def multi_seed_recs(rec, seed_ids, k=10):
    E, genres, artists, ids = taste_mod.from_recommender(rec)
    seed_rows = [np.flatnonzero(ids == s)[0] for s in seed_ids]
    scores = taste_mod.score_centroid(E, seed_rows)
    top = taste_mod.recommend(scores, seed_rows, artists, k=k)
    return pd.DataFrame({
        "track_id": ids[top],
        "artist": rec.tracks_.loc[ids[top], ("artist", "name")].values,
        "title": rec.tracks_.loc[ids[top], ("track", "title")].values,
        "genre": rec.tracks_.loc[ids[top], ("track", "genre_top")].values,
    })


baseline_recs = multi_seed_recs(rec_baseline, SEED_IDS)
heard_recs = multi_seed_recs(rec_heard, SEED_IDS)

overlap = set(baseline_recs.track_id) & set(heard_recs.track_id)
print(f"{len(overlap)} / 10 tracks shared between the baseline and heard centroid recommendations")

1 / 10 tracks shared between the baseline and heard centroid recommendations


In [12]:
print("baseline (518 columns):")
display(baseline_recs)
print("\nheard (154 columns):")
display(heard_recs)

baseline (518 columns):


,track_id,artist,title,genre
0,21995,Katapulto,zero rhythm dollar boy,Pop
1,68891,Broke For Free,Building The Sun,Electronic
2,48442,Bass Assassin,8bitDetective,Electronic
3,87069,Waste Disposal Machine,I Sing the Body Electric (first take SFI remix),Electronic
4,55242,Mastermind XS,The Essence Of Bottled Light,International
5,36998,Exteenager,bonsoir tiroir!,Electronic
6,56030,Mastermind XS,All The Stars,International
7,55241,Mastermind XS,Serious Problem,International
8,42018,Electronischebasisgeluide,La boite a track (Spain),Electronic
9,141166,godmanwho,10 LIKE LOATHE OR LOVE IT,Hip-Hop



heard (154 columns):


,track_id,artist,title,genre
0,89841,Not The 1s,You Dress Like an Asshole (prod. by Lunice),Hip-Hop
1,87069,Waste Disposal Machine,I Sing the Body Electric (first take SFI remix),Electronic
2,114290,Track Jackit,Elevation,Electronic
3,114293,Track Jackit,Night In Chicago,Electronic
4,10527,Funky Terrorist,r u serious,Experimental
5,129875,Tzelalot,Enchant Down Babylon,International
6,85317,Titus 12,Human Face,Electronic
7,104283,Beatoven,Wanna See My Spaceship,Electronic
8,153337,DRVN,The Vent,Hip-Hop
9,14869,violett,ukelele,Electronic


In [13]:
print("baseline genre spread:")
print(baseline_recs.genre.value_counts())
print("\nheard genre spread:")
print(heard_recs.genre.value_counts())

baseline genre spread:
genre
Electronic       5
International    3
Pop              1
Hip-Hop          1
Name: count, dtype: int64

heard genre spread:
genre
Electronic       6
Hip-Hop          2
Experimental     1
International    1
Name: count, dtype: int64


**Listen:** the three seeds, then each space's top-10 for them.

In [14]:
for seed_id in SEED_IDS:
    meta = tracks_baseline.loc[seed_id]
    play(audio_path(seed_id), f"SEED {seed_id}  {meta[('artist','name')]} — {meta[('track','title')]}")

print("\n--- baseline (518 columns) ---")
for row in baseline_recs.itertuples():
    play(audio_path(row.track_id), f"{row.artist} — {row.title}  [{row.genre}]")

print("\n--- heard (154 columns) ---")
for row in heard_recs.itertuples():
    play(audio_path(row.track_id), f"{row.artist} — {row.title}  [{row.genre}]")

SEED 704  Fósforo — Mano De Dios


SEED 1083  Magic Lantern — Feasting on Energy


SEED 56690  Corty — Trod Along (vocals: Preecha Kungo)



--- baseline (518 columns) ---
Katapulto — zero rhythm dollar boy  [Pop]


Broke For Free — Building The Sun  [Electronic]


...

Tzelalot — Enchant Down Babylon  [International]


Titus 12 — Human Face  [Electronic]


Beatoven — Wanna See My Spaceship  [Electronic]


DRVN — The Vent  [Hip-Hop]


violett — ukelele  [Electronic]


## 3. Control — does heard space even work, with no external audio involved?

Manual listening on part 1's results said the similarity was thin. Before that
indicts the recommender, rule out the other suspect: part 1's external seed went
through an *approximate* reconstruction of FMA's mfcc pipeline (see the intro).
Catalogue tracks carry no such approximation — they're the real, FMA-computed
features the space was fit on. If a real catalogue seed's heard-space top-10
also sounds unrelated, the problem is the feature space, not the approximation.
If it sounds clearly related, the approximation (or FMA-small's genre coverage
for this particular seed) is the more likely explanation.

A numeric check first: is the external seed sitting in an unusually empty part
of the space, or a normal one?

In [15]:
rng = np.random.default_rng(0)
sample_ids = rng.choice(rec_heard.track_ids_, size=300, replace=False)
top1 = []
for tid in sample_ids:
    d, _ = rec_heard.index_.kneighbors(rec_heard.embedding_.loc[[tid]], n_neighbors=2)
    top1.append(d[0][1])
top1 = np.array(top1)
print(f"catalogue-internal top-1 distance: mean={top1.mean():.3f} median={np.median(top1):.3f} "
      f"p10={np.percentile(top1, 10):.3f} p90={np.percentile(top1, 90):.3f}")
print(f"external seed's own top-1 distance: {seed_recs['distance'].iloc[0]:.3f}  "
      "(inside the normal range means the catalogue isn't simply empty near it)")

catalogue-internal top-1 distance: mean=0.269 median=0.271 p10=0.151 p90=0.397
external seed's own top-1 distance: 0.333  (inside the normal range means the catalogue isn't simply empty near it)


**Listen:** a real catalogue seed and its heard-space top-10, no external audio
involved anywhere in this cell.

In [16]:
CONTROL_SEED = 2  # AWOL -- Food, Hip-Hop; used throughout FOR_TIM.md as the reference example

meta = tracks_heard.loc[CONTROL_SEED]
play(audio_path(CONTROL_SEED),
     f"SEED {CONTROL_SEED}  {meta[('artist','name')]} — {meta[('track','title')]}  [{meta[('track','genre_top')]}]")
for track_id, row in rec_heard.similar_to(CONTROL_SEED, n=10).iterrows():
    play(audio_path(track_id),
         f"#{row['rank']}  distance={row['distance']:.3f}  {row['artist']} — {row['title']}  [{row['genre']}]")

SEED 2  AWOL — Food  [Hip-Hop]


#1  distance=0.315  Sun Sunych ft. DanBrown — Toys (ft. DanBrown)  [Hip-Hop]


#2  distance=0.380  Gates — I Remember When  [Hip-Hop]


#3  distance=0.382  SK — woke up feeling blessed  [Hip-Hop]


#4  distance=0.387  SK — On the daily  [Hip-Hop]


...

#6  distance=0.391  Vanatei ft. Semi — B*tch You Ain't A Barbie  [Hip-Hop]


#7  distance=0.395  Donnie Ozone — Get Paid (Mouth Beat Mix) (Featuring DJ Phazer)  [Hip-Hop]


#8  distance=0.400  J-K — Aperitivos  [Hip-Hop]


#9  distance=0.400  K. Sparks — Blue Real Talk  [Hip-Hop]


#10  distance=0.402  Donnie Ozone — Get Paid (Full Mix) (Featuring DJ Phazer)  [Hip-Hop]


### Was Hip-Hop just a favourable case?

One seed proves nothing about the other seven genres. Measure genre
agreement@10 (share of the top-10 sharing the seed's own genre label) across
30 seeds per genre, all in heard space.

In [17]:
genre_rng = np.random.default_rng(1)
agreement_rows = []
for genre in sorted(genre_labels(tracks_heard).dropna().unique()):
    pool = genre_labels(tracks_heard)[genre_labels(tracks_heard) == genre].index.to_numpy()
    sample = genre_rng.choice(pool, size=min(30, len(pool)), replace=False)
    for seed_id in sample:
        recs = rec_heard.similar_to(int(seed_id), n=10)
        agreement_rows.append({"genre": genre, "seed_id": int(seed_id),
                                "agreement@10": (recs["genre"] == genre).mean(),
                                "mean_distance": recs["distance"].mean()})

agreement_df = pd.DataFrame(agreement_rows)
agreement_summary = agreement_df.groupby("genre")[["agreement@10", "mean_distance"]].mean().round(3)
agreement_summary["n_seeds"] = agreement_df.groupby("genre").size()
agreement_summary = agreement_summary.sort_values("agreement@10")
agreement_summary

,agreement@10,mean_distance,n_seeds
genre,,,
Pop,0.240,0.382,30
Experimental,0.257,0.326,30
Rock,0.460,0.324,30
Electronic,0.480,0.328,30
Hip-Hop,0.490,0.332,30
International,0.543,0.326,30
Folk,0.547,0.356,30
Instrumental,0.613,0.317,30


Genre agreement swings more than 2x by genre — Hip-Hop (used above) sits above
the overall mean, not at it. The external seed's actual Spotify recommendations
(Soul, Naima Blue, "Beauty In Imperfection") read as chill/soul/pop, which is
plausibly the weakest corner of this catalogue rather than a typical one.

**Listen:** one seed from the weakest genre, one from the strongest, both in
heard space — same audio-free control as above.

In [18]:
weakest_genre = agreement_summary.index[0]
strongest_genre = agreement_summary.index[-1]

for genre, label_text in [(weakest_genre, "WEAKEST"), (strongest_genre, "STRONGEST")]:
    seed_id = int(agreement_df[agreement_df["genre"] == genre].sort_values("seed_id").iloc[0]["seed_id"])
    meta = tracks_heard.loc[seed_id]
    print(f"\n=== {label_text}: {genre} (mean agreement@10 = {agreement_summary.loc[genre, 'agreement@10']:.2f}) ===")
    play(audio_path(seed_id),
         f"SEED {seed_id}  {meta[('artist','name')]} — {meta[('track','title')]}  [{genre}]")
    for track_id, row in rec_heard.similar_to(seed_id, n=10).iterrows():
        play(audio_path(track_id),
             f"#{row['rank']}  distance={row['distance']:.3f}  {row['artist']} — {row['title']}  [{row['genre']}]")


=== WEAKEST: Pop (mean agreement@10 = 0.24) ===
SEED 3538  Cryptacize — Say You Will  [Pop]


#1  distance=0.285  Gwilly Edmondez — Tarantella Tomatoes  [Experimental]


#2  distance=0.314  Ed Askew — Piano 3  [Folk]


#3  distance=0.317  Twins of El Dorado — "Cats"/Interlude  [Experimental]


#4  distance=0.321  Humble Tripe — Carnival Song  [Folk]


...

#6  distance=0.416  Lucky Dragons — new homes  [Experimental]


#7  distance=0.423  Podington Bear — Whistle Work  [Instrumental]


#8  distance=0.423  Richard Jonas — Bea6 (Oelek dromer rmx)  [Electronic]


#9  distance=0.428  Blue Dot Sessions — Bkls  [Instrumental]


#10  distance=0.429  This One — No Time For Lookin' Back  [Electronic]


## 4. Would more features help? heard vs heard_wide vs all — same catalogue seed

`heard` (154 cols) is mfcc + rhythm + hpss_ratio. `heard_wide` (238 cols) adds
back the rest of FMA's timbre descriptors — spectral_contrast, centroid,
bandwidth, rolloff, zcr, rmse — still no chroma/tonnetz. `all` (518, our
"baseline" above) adds chroma back in too.

Worth being upfront about what the team's own listening test already found on
this exact question, even though it was measured on *old*-space-selected pairs
(the biggest open hole your teammate's README flags): `heard` correlated -0.358
with human ratings, `heard_wide` -0.213 (not significant, p=0.017), `all` ~0
(p=0.58, no relationship). More features didn't help there — chroma diluted the
signal rather than adding to it. That test has never been rerun on
heard-space-selected pairs, so this section is a fast, informal look, not a
replacement for one.

In [19]:
X_heard_wide = space("heard_wide")
tracks_heard_wide = tracks_baseline.loc[X_heard_wide.index]
Xhw_scaled, scaler_heard_wide = scale_features(X_heard_wide, method="standard")
pca_heard_wide = fit_pca(Xhw_scaled, n_components=0.90)
rec_heard_wide = TrackRecommender(scaler_heard_wide, pca_heard_wide).fit(X_heard_wide, tracks_heard_wide)
print(f"heard_wide: {X_heard_wide.shape[1]} columns -> {pca_heard_wide.n_components_} components, "
      f"{len(tracks_heard_wide)} tracks")

heard_wide: 238 columns -> 81 components, 7993 tracks


**Listen:** the same seed as part 3, across all three spaces.

In [20]:
play(audio_path(CONTROL_SEED), f"SEED {CONTROL_SEED} (same as part 3)")

for name, rec in [("heard (154)", rec_heard), ("heard_wide (238)", rec_heard_wide), ("all (518)", rec_baseline)]:
    print(f"\n--- {name} ---")
    for track_id, row in rec.similar_to(CONTROL_SEED, n=5).iterrows():
        play(audio_path(track_id),
             f"  #{row['rank']}  distance={row['distance']:.3f}  {row['artist']} — {row['title']}  [{row['genre']}]")

SEED 2 (same as part 3)



--- heard (154) ---
  #1  distance=0.315  Sun Sunych ft. DanBrown — Toys (ft. DanBrown)  [Hip-Hop]


  #2  distance=0.380  Gates — I Remember When  [Hip-Hop]


  #3  distance=0.382  SK — woke up feeling blessed  [Hip-Hop]


  #4  distance=0.387  SK — On the daily  [Hip-Hop]


...


--- all (518) ---
  #1  distance=0.424  BrokeMC — In the Dark  [Hip-Hop]


  #2  distance=0.425  K. Sparks — Blue Real Talk  [Hip-Hop]


  #3  distance=0.448  Hi-Rez — Relax (Prod. Joel Johnston)  [Hip-Hop]


  #4  distance=0.477  Martin R. — Acidamine  [Electronic]


  #5  distance=0.479  CM & Tha Silent Partner — My Place  [Hip-Hop]


## 5. Does more catalogue (`fma_medium`, 25k tracks) actually help?

Rebuilt heard space on `fma_medium` — the same rhythm/separation extraction,
just run against 3x the audio (`FMA_AUDIO_DIR=data/fma_medium`,
`--subset medium`; `modeling/data.py`'s subset filter had to be fixed first —
FMA's "medium" label is exclusive of "small" in the raw csv, not cumulative,
so the old exact-match filter silently returned only the medium-only 17,000).

Building this table directly here rather than through `features.full_table()`:
that function's `loader()` calls use `rhythm.load()`'s *default* path argument,
which is bound once at import time — so it would keep reading the small-catalog
csvs no matter what the output files on disk say. A real, if narrow, bug worth
knowing about if anyone reuses `full_table()` across subsets in one process.

In [21]:
import modeling.rhythm as rhythm_module
rhythm_module.AUDIO_DIR = REPO_ROOT / "data" / "fma_medium"

X_medium_518, tracks_medium_518 = load_fma("medium")
rhythm_medium = pd.read_csv(REPO_ROOT / "data" / "rhythm_features_medium.csv", index_col=0, header=[0, 1, 2])
sep_medium = pd.read_csv(REPO_ROOT / "data" / "separation_features_medium.csv", index_col=0, header=[0, 1, 2])

mfcc_medium = X_medium_518.loc[:, X_medium_518.columns.get_level_values(0) == "mfcc"]
# "heard" is mfcc + rhythm + hpss_ratio only -- separation.py also writes
# mfcc_harmonic/mfcc_percussive (the rejected 80-column experiment), so those
# have to be filtered out here or X_heard_medium silently gets 234 columns
# instead of 154 and no longer matches what the small-catalogue space is.
hpss_medium = sep_medium.loc[:, sep_medium.columns.get_level_values(0) == "hpss_ratio"]
common = mfcc_medium.index.intersection(rhythm_medium.index).intersection(hpss_medium.index)
X_heard_medium = pd.concat([mfcc_medium.loc[common], rhythm_medium.loc[common], hpss_medium.loc[common]], axis=1)
tracks_heard_medium = tracks_medium_518.loc[common]

Xm_scaled, scaler_medium = scale_features(X_heard_medium, method="standard")
pca_medium = fit_pca(Xm_scaled, n_components=0.90)
rec_medium = TrackRecommender(scaler_medium, pca_medium).fit(X_heard_medium, tracks_heard_medium)
print(f"medium heard: {X_heard_medium.shape[1]} columns -> {pca_medium.n_components_} components, "
      f"{len(tracks_heard_medium)} tracks (3.1x fma-small)")

medium heard: 154 columns -> 57 components, 24977 tracks (3.1x fma-small)


### The external seed, rescored — small catalogue vs. medium

In [22]:
seed_row_medium = extract_heard_features(SEED_PATH, X_heard_medium.columns, track_id=990000099)
seed_emb_medium = transform(seed_row_medium.to_frame().T, scaler_medium, pca_medium)

d, idx = rec_medium.index_.kneighbors(seed_emb_medium, n_neighbors=N)
seed_recs_medium = rec_medium._with_metadata(rec_medium.track_ids_[idx[0]], d[0], np.arange(1, N + 1))
seed_recs_medium

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?
[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


,rank,distance,artist,title,genre
track_id,,,,,
51260,1,0.317184,Les Filles et les Garçons,I Sing Despair,Pop
127498,2,0.323394,Blue Dot Sessions,Scratcher,Instrumental
42374,3,0.325142,Broke For Free,My Luck,Electronic
30895,4,0.334957,Digi G'Alessio,Camuffarsi e Mantenere la Calma (Al Pianobar),Electronic
97544,5,0.344332,Amitron_7,Escape Under Cover of Night,Electronic
107426,6,0.344949,UncleBibby,Chunky Worm Stew,Electronic
58234,7,0.345509,The Carrier Wave,The Gus,Electronic
47657,8,0.346863,Haute Culture,Post,Electronic
14348,9,0.351042,Pitch Boys,Pod 03,Electronic


In [23]:
def cosine_distance_to(embeddings, v):
    vu = v / np.linalg.norm(v)
    eu = embeddings / np.linalg.norm(embeddings, axis=1, keepdims=True)
    return 1 - eu @ vu


catalog_dist_medium = np.sort(cosine_distance_to(rec_medium.embedding_.to_numpy(), seed_emb_medium.to_numpy()[0]))
catalog_size_medium = len(catalog_dist_medium)


def catalog_rank_medium(distance):
    return int(np.searchsorted(catalog_dist_medium, distance)) + 1


medium_rows = []
for folder in ["spotify_tests", "youtube_tests"]:
    for path in sorted((DATA_RAW / folder).glob("*.mp3")):
        if "Elyjah" in path.name:
            continue
        feat = extract_heard_features(path, X_heard_medium.columns)
        emb = transform(feat.to_frame().T, scaler_medium, pca_medium).to_numpy()[0]
        distance = float(cosine_distance_to(emb[np.newaxis, :], seed_emb_medium.to_numpy()[0])[0])
        medium_rows.append({"platform": folder, "file": path.name, "distance": distance,
                             "rank": catalog_rank_medium(distance)})

medium_scored = pd.DataFrame(medium_rows)
medium_scored["percentile"] = medium_scored["rank"] / catalog_size_medium

comparison = medium_scored.groupby("platform")["percentile"].mean().to_frame("medium_percentile")
comparison["small_percentile"] = pd.Series({
    "spotify_tests": scored[scored.platform == "spotify_tests"]["catalog_rank"].mean() / catalog_size,
    "youtube_tests": scored[scored.platform == "youtube_tests"]["catalog_rank"].mean() / catalog_size,
})
comparison

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


...

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?
[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


,medium_percentile,small_percentile
platform,,
spotify_tests,0.085839,0.086673
youtube_tests,0.051616,0.051059


Same relative position, 3x the catalogue — a bigger library didn't move this
seed closer to what Spotify/YouTube picked. That argues against "not enough
tracks" as the explanation.

### What 3x the catalogue did change: genre balance

`fma_medium` is not genre-balanced the way `fma_small` is (1000/genre, by
design). Rock and Electronic dominate it. Rerun the genre-agreement@10 sweep
here and line it up against how big each genre actually is.

In [24]:
medium_labels = genre_labels(tracks_heard_medium)
medium_rng = np.random.default_rng(1)
medium_agreement_rows = []
for genre in sorted(medium_labels.dropna().unique()):
    pool = medium_labels[medium_labels == genre].index.to_numpy()
    if len(pool) < 10:
        continue
    sample = medium_rng.choice(pool, size=min(30, len(pool)), replace=False)
    for seed_id in sample:
        recs = rec_medium.similar_to(int(seed_id), n=10)
        medium_agreement_rows.append({"genre": genre, "agreement@10": (recs["genre"] == genre).mean()})

medium_agreement_df = pd.DataFrame(medium_agreement_rows)
medium_agreement_summary = medium_agreement_df.groupby("genre")["agreement@10"].mean().round(3)
medium_counts = medium_labels.value_counts()
genre_table = pd.DataFrame({"agreement@10": medium_agreement_summary,
                             "n_in_medium": medium_counts.reindex(medium_agreement_summary.index)})
genre_table.sort_values("agreement@10")

,agreement@10,n_in_medium
genre,,
Easy Listening,0.019,21
Soul-RnB,0.133,154
Pop,0.150,1186
Blues,0.190,74
Country,0.240,178
Experimental,0.247,2248
Jazz,0.250,384
Instrumental,0.317,1348
Spoken,0.330,118


Agreement@10 now tracks catalogue share almost directly — Rock (7,098 tracks)
0.75, Electronic (6,311) 0.72, against Pop (1,186, barely grown from small's
1,000) dropping to 0.15 and Soul-RnB (154) to 0.13. More candidates from the
big genres crowd out genuinely-similar minority-genre neighbours in a plain
kNN. So the honest update: `fma_medium` didn't fix the coverage gap and made
minority-genre crowding measurably worse — this is the same phenomenon
`TrackRecommender.crowding()`'s docstring already describes, just now visible
by genre instead of by seed. A genre-balanced sample of `fma_medium`, or a
crowding-aware re-ranking, looks more promising than raw catalogue size.

**Listen:** the Pop control seed from part 3 (`SEED 3538`), small catalogue vs.
medium — same seed, same method, only the pool size changed.

In [25]:
pop_seed_id = int(agreement_df[agreement_df["genre"] == weakest_genre].sort_values("seed_id").iloc[0]["seed_id"])

print("--- small catalogue (7,993 tracks) ---")
for track_id, row in rec_heard.similar_to(pop_seed_id, n=10).iterrows():
    play(audio_path(track_id), f"#{row['rank']}  {row['artist']} — {row['title']}  [{row['genre']}]")

print("\n--- medium catalogue (24,977 tracks) ---")
rhythm_module.AUDIO_DIR = REPO_ROOT / "data" / "fma_medium"
for track_id, row in rec_medium.similar_to(pop_seed_id, n=10).iterrows():
    play(audio_path(track_id), f"#{row['rank']}  {row['artist']} — {row['title']}  [{row['genre']}]")

--- small catalogue (7,993 tracks) ---
#1  Gwilly Edmondez — Tarantella Tomatoes  [Experimental]


#2  Ed Askew — Piano 3  [Folk]


#3  Twins of El Dorado — "Cats"/Interlude  [Experimental]


#4  Humble Tripe — Carnival Song  [Folk]


#5  Levi Weaver — We're Tornadoes When We Dance  [Folk]


...

#6  Ehran Elisha, Harold Rubin and Haim Elisha — The Father, The Son, and The Harold Rubin  [Jazz]


#7  Rachel Mason — The Chair  [Folk]


#8  Rachel Mason — Wild Fish  [Folk]


#9  Ed Askew — Piano 3  [Folk]


#10  No Nature — Pop song  [Pop]


## 6. A genre-balanced sample of fma_medium

Cap the dominant genres so they can't crowd out everyone else's neighbours,
while keeping every track from genres already below the cap — so the minority
genres `fma_medium` newly introduces (Classical, Jazz, Country, Soul-RnB,
Spoken, Blues, Easy Listening, Old-Time/Historic — none of these exist in
`fma_small`'s balanced 8) are kept in full rather than diluted further.

Cap chosen at 1,500: high enough that Folk (1,518) and Pop (1,186) are barely
touched, low enough that Rock (7,098) and Electronic (6,311) drop to a fifth of
their size.

In [26]:
CAP = 1500
balance_rng = np.random.default_rng(7)
keep_ids = []
for genre in medium_labels.dropna().unique():
    pool = medium_labels[medium_labels == genre].index.to_numpy()
    keep_ids.extend(balance_rng.choice(pool, size=min(CAP, len(pool)), replace=False))
keep_ids = pd.Index(keep_ids)

X_balanced = X_heard_medium.loc[keep_ids]
tracks_balanced = tracks_heard_medium.loc[keep_ids]
print(f"balanced sample: {len(keep_ids)} tracks (from {len(tracks_heard_medium)} in fma_medium)")
print(genre_labels(tracks_balanced).value_counts())

Xb_scaled, scaler_balanced = scale_features(X_balanced, method="standard")
pca_balanced = fit_pca(Xb_scaled, n_components=0.90)
rec_balanced = TrackRecommender(scaler_balanced, pca_balanced).fit(X_balanced, tracks_balanced)

balanced sample: 13110 tracks (from 24977 in fma_medium)
(track, genre_top)
Hip-Hop                1500
Rock                   1500
Folk                   1500
Experimental           1500
Electronic             1500
Instrumental           1348
Pop                    1186
International          1018
Classical               619
Old-Time / Historic     510
Jazz                    384
Country                 178
Soul-RnB                154
Spoken                  118
Blues                    74
Easy Listening           21
Name: count, dtype: int64


Genre agreement@10, all three catalogues side by side:

In [27]:
balanced_labels = genre_labels(tracks_balanced)
brng = np.random.default_rng(1)
balanced_rows = []
for genre in sorted(balanced_labels.dropna().unique()):
    pool = balanced_labels[balanced_labels == genre].index.to_numpy()
    if len(pool) < 10:
        continue
    sample = brng.choice(pool, size=min(30, len(pool)), replace=False)
    for seed_id in sample:
        recs = rec_balanced.similar_to(int(seed_id), n=10)
        balanced_rows.append({"genre": genre, "agreement@10": (recs["genre"] == genre).mean()})

balanced_summary = pd.DataFrame(balanced_rows).groupby("genre")["agreement@10"].mean().round(3)
three_way = agreement_df.groupby("genre")["agreement@10"].mean().round(3).to_frame("small")
three_way["medium"] = genre_table["agreement@10"]
three_way["balanced"] = balanced_summary
three_way.sort_values("balanced", ascending=False)

,small,medium,balanced
genre,,,
Hip-Hop,0.490,0.553,0.597
Folk,0.547,0.363,0.487
International,0.543,0.420,0.473
Electronic,0.480,0.717,0.393
Rock,0.460,0.750,0.377
Instrumental,0.613,0.317,0.367
Experimental,0.257,0.247,0.240
Pop,0.240,0.150,0.123


Honest reading, not the one I expected: balancing fixed what it was built to
fix (Rock/Electronic's agreement@10 both roughly halve, since they can no
longer win on raw candidate count) — but it did **not** rescue Pop. Pop is
still near the bottom, similar to or worse than at medium scale. That lines up
with part 3's dispersion measurement: Pop's own tracks don't cluster tightly
around each other (0.849 mean distance to their own genre centroid, worst of
all eight original genres) — crowding wasn't Pop's problem, acoustic
incoherence was, and rebalancing the catalogue can't fix a label that doesn't
correspond to a consistent sound.

### Does the external seed's ranking move?

In [28]:
seed_row_balanced = extract_heard_features(SEED_PATH, X_heard_medium.columns, track_id=990000199)
seed_vec_balanced = transform(seed_row_balanced.to_frame().T, scaler_balanced, pca_balanced).to_numpy()[0]

catalog_dist_balanced = np.sort(cosine_distance_to(rec_balanced.embedding_.to_numpy(), seed_vec_balanced))
size_balanced = len(catalog_dist_balanced)

balanced_rows2 = []
for folder in ["spotify_tests", "youtube_tests"]:
    for path in sorted((DATA_RAW / folder).glob("*.mp3")):
        if "Elyjah" in path.name:
            continue
        feat = extract_heard_features(path, X_heard_medium.columns)
        emb = transform(feat.to_frame().T, scaler_balanced, pca_balanced).to_numpy()[0]
        d = float(cosine_distance_to(emb[np.newaxis, :], seed_vec_balanced)[0])
        rank = int(np.searchsorted(catalog_dist_balanced, d)) + 1
        balanced_rows2.append({"platform": folder, "percentile": rank / size_balanced})

balanced_scored = pd.DataFrame(balanced_rows2)
comparison["balanced_percentile"] = balanced_scored.groupby("platform")["percentile"].mean()
comparison

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?
[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?
[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


...

[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?
[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


[src/libmpg123/id3.c:process_comment():587] error: No comment text / valid description?


,medium_percentile,small_percentile,balanced_percentile
platform,,,
spotify_tests,0.085839,0.086673,0.085422
youtube_tests,0.051616,0.051059,0.053699


Barely moves, again. Three different catalogues — small, medium, balanced —
all land within about half a percentage point of each other on where Spotify's
and YouTube's own picks rank. That's a fairly strong signal that catalogue
composition was never the lever for *this specific comparison* — it's either
the platforms' collaborative-filtering signal (which no amount of our own
audio-only catalogue engineering reaches), or something about what heard space
measures. Where balancing *did* help: the seed's own top-10 in the balanced
catalogue includes Soul-RnB tracks for the first time — a genre that doesn't
exist at all in fma_small and was still swamped at medium scale. Whether that's
a better recommendation is a listening-check question, not a numbers one.

**Listen:** the seed's own top-10 in the balanced catalogue.

In [29]:
rhythm_module.AUDIO_DIR = REPO_ROOT / "data" / "fma_medium"
d, idx = rec_balanced.index_.kneighbors(seed_vec_balanced.reshape(1, -1), n_neighbors=N)
balanced_seed_recs = rec_balanced._with_metadata(rec_balanced.track_ids_[idx[0]], d[0], np.arange(1, N + 1))
for track_id, row in balanced_seed_recs.iterrows():
    play(audio_path(track_id), f"#{row['rank']}  distance={row['distance']:.3f}  {row['artist']} — {row['title']}  [{row['genre']}]")

/Users/tim/neuefische_course/capstone-matchas-tastebridge/.venv/lib/python3.13/site-packages/sklearn/utils/validation.py:2830: UserWarning: X does not have valid feature names, but NearestNeighbors was fitted with feature names
  warnings.warn(


#1  distance=0.303  Blue Dot Sessions — Scratcher  [Instrumental]


#2  distance=0.320  Les Filles et les Garçons — I Sing Despair  [Pop]


#3  distance=0.338  Haute Culture — Post  [Electronic]


#4  distance=0.361  Tracky Birthday — Eöööhh! (with The Discoghosts)  [Soul-RnB]


...

#6  distance=0.373  Tardiss — Mouse Run  [Electronic]


#7  distance=0.373  The Discoghosts — Can Opener  [Soul-RnB]


#8  distance=0.375  Vim — a tune of sorts  [Electronic]


#9  distance=0.385  Duke Hugh — catch a wave  [Hip-Hop]


#10  distance=0.386  Andre Jetson — Caprisqui  [Electronic]
